# 05 · SVM — Supervised · Classification & Regression

**This notebook demonstrates classification with `SVC`.** For numerical targets, scikit-learn provides support vector regression through `SVR`.

**Question:** How can a model separate classes while allowing some mistakes?

**Prerequisites:** Points, classes, and validation from notebooks 02 and 04. **Time:** 35–45 minutes.

A **support vector machine (SVM)** learns a decision boundary. In a linear SVM it is a straight line in two dimensions. Training balances a wide margin against penalties for points inside the margin or on the wrong side. **Support vectors** are training examples that help determine the boundary.

## Run and explore

Run cells from top to bottom with **Shift + Enter**, or select **Run → Run All Cells**. Each notebook is independent. You can use the plots without understanding their drawing code. Read the prediction prompt, move a slider or choose an option, then compare the outcome with your prediction.

All data is synthetic. Controls select results computed when the cell runs; they do not train a new model on every mouse movement. To change the dataset, edit its settings in the code and rerun that cell and the cells below it. Seeds keep the examples repeatable. Hover for values; double-click to reset zoom.

## Workshop delivery plan (50–70 minutes)

**Opening question:** What makes a wide margin useful, and when is a curved boundary justified?

By the end, learners should be able to:

- interpret margins and support vectors
- explain C and gamma
- separate fit from generalization

Suggested flow: 5 minutes for the opening prediction, 12 minutes for the first live experiment, 15 minutes for paired core exercises, 10 minutes for the second demonstration, 10 minutes for group explanation, and 5–15 minutes for debrief or stretch work. Ask learners to state a prediction before touching a control and cite a visible value, boundary, or metric in every explanation.

## Our shared experiment

Two interleaving moon shapes have known categories, **class 0** and **class 1**. Each point has two numerical inputs, called **features**. The goal is to predict the category of a new point.

We fit models on **training** examples and compare settings on separate **validation** examples. Because we explore many settings, these are validation results, not a final test of the selected model. In a real project, preserve another untouched test set for that final check.

We **standardize** both features using the training mean and standard deviation. This puts their scales on comparable terms; it matters when distance determines behavior. The axes below are measured in training standard deviations, not the original units. Standardization does not make every distribution normal.

In [1]:
import numpy as np
import pandas as pd
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from IPython.display import display
from sklearn.datasets import make_moons, make_blobs
from sklearn.model_selection import train_test_split
from sklearn.preprocessing import StandardScaler
from sklearn.metrics import accuracy_score
import plotly.io as pio
pio.renderers.default = "plotly_mimetype+notebook"
pio.templates.default = "plotly_white"
BLUE, ORANGE, GREEN = "#2563eb", "#c2410c", "#15803d"

from sklearn.svm import SVC

# The same data and split are used in the KNN and SVM notebooks.
X_raw, y = make_moons(n_samples=240, noise=0.24, random_state=42)
X_train_raw, X_val_raw, y_train, y_val = train_test_split(
    X_raw, y, test_size=0.25, stratify=y, random_state=12)
scaler = StandardScaler().fit(X_train_raw)  # Learn scaling from training inputs only.
X_train = scaler.transform(X_train_raw)
X_val = scaler.transform(X_val_raw)
axis = np.linspace(-3.2, 3.2, 85)
gx, gy = np.meshgrid(axis, axis)  # A grid of locations at which to ask the model for a class.
grid = np.column_stack([gx.ravel(), gy.ravel()])
print(f"{len(y_train)} training examples; {len(y_val)} validation examples")

180 training examples; 60 validation examples


## Reading the diagrams

Pale regions show predicted classes. Circles are actual class 0; diamonds are actual class 1. Larger markers with black edges are validation points. Open rings identify support vectors from the training set.

The contour labeled **0** is the decision boundary. The **−1 and +1** contours are margin levels of the SVM's decision score. This score is not a probability. For a linear SVM, these are parallel margin lines. With an RBF kernel, contours in this input plot can curve; do not interpret their input-space distances as a constant geometric margin.

The drawing code below is a reusable helper. Focus on the model settings in the experiments that follow.

In [2]:
# Drawing helper: models and their predictions are prepared in the next cells.
def classifier_plot(cases, control_label, initial=0, margins=False):
    case = cases[initial]
    fig = go.Figure(go.Heatmap(x=axis, y=axis, z=case["regions"],
        zmin=0, zmax=1, colorscale=[[0,"#dbeafe"],[0.499,"#dbeafe"],
                                  [0.5,"#ffedd5"],[1,"#ffedd5"]],
        showscale=False, hoverinfo="skip"))
    for split, inputs, labels in [("Train",X_train,y_train),("Validation",X_val,y_val)]:
        for cls, color in [(0,BLUE),(1,ORANGE)]:
            points = inputs[labels==cls]
            fig.add_scatter(x=points[:,0],y=points[:,1],mode="markers",
                name=f"{split} · class {cls}",
                marker=dict(color=color, symbol=("circle" if cls==0 else "diamond"),
                    size=(6 if split=="Train" else 11),
                    line=dict(color=("white" if split=="Train" else "black"),width=1.5)))
    support = case.get("support",np.empty((0,2)))
    fig.add_scatter(x=support[:,0],y=support[:,1],mode="markers",name="Support vectors",
        showlegend=margins, marker=dict(symbol="circle-open",size=15,color="black",line=dict(width=1.5)))
    fig.add_trace(go.Contour(x=axis,y=axis,z=case["scores"],showscale=False,
        contours=dict(start=(-1 if margins else 0),end=(1 if margins else 0),size=1,
                      coloring="none",showlabels=True),
        line=dict(color="#334155",width=1.5),hoverinfo="skip",name="Decision contours"))
    steps=[]
    for c in cases:
        sv=c.get("support",np.empty((0,2)))
        steps.append(dict(label=c["label"].split(" = ")[-1],method="update",args=[
            {"z":[c["regions"],None,c["scores"]],
             "x":[axis,sv[:,0],axis],"y":[axis,sv[:,1],axis]},
            {"title.text":c["title"]},[0,5,6]]))
    fig.update_layout(title=case["title"],height=620,
        xaxis=dict(title="Feature 1 (standardized)",range=[-3.2,3.2],constrain="domain"),
        yaxis=dict(title="Feature 2 (standardized)",range=[-3.2,3.2],scaleanchor="x"),
        margin=dict(t=100,b=110),legend=dict(font=dict(size=11)),
        sliders=[dict(active=initial,currentvalue=dict(prefix=control_label),steps=steps)])
    return fig

def classifier_case(model,label):
    model.fit(X_train,y_train)
    scores=(model.decision_function(grid) if hasattr(model,"decision_function")
            else model.predict_proba(grid)[:,1]-0.5)
    train_acc=accuracy_score(y_train,model.predict(X_train))
    val_acc=accuracy_score(y_val,model.predict(X_val))
    return dict(label=label,regions=model.predict(grid).reshape(gx.shape),
        scores=scores.reshape(gx.shape),
        support=(model.support_vectors_ if hasattr(model,"support_vectors_") else np.empty((0,2))),
        title=f"{label}<br>Training accuracy: {train_acc:.1%} · Validation accuracy: {val_acc:.1%}",
        model=model,train_acc=train_acc,val_acc=val_acc)

## 1. C: how strongly to penalize margin violations

**C** controls the penalty for margin violations relative to regularization, which discourages overly complex fits. Smaller C permits more violations in exchange for stronger regularization. Larger C penalizes violations more strongly. A violation can mean a correctly classified point inside the margin, not only a classification mistake.

**Predict:** Can any choice of C make a straight line follow two curved moon shapes perfectly? Move the slider and compare training and validation accuracy.

In [3]:
c_values=[0.01,0.1,1,10,100]
linear_cases=[classifier_case(SVC(kernel="linear",C=c),f"Linear SVM · C = {c}") for c in c_values]
linear_fig=classifier_plot(linear_cases,"C: ",initial=2,margins=True)
linear_fig.show()

## 2. A kernel changes the shapes the model can express

A **kernel** lets an SVM compare examples in a way that can create nonlinear boundaries. The **RBF (radial basis function)** kernel uses similarity that decreases with squared distance. We will keep C=1 and change **gamma**, which controls how quickly that similarity decreases.

Small gamma gives each point a broad influence. Large gamma makes influence more local, which can produce small islands around training examples.

**Predict:** Will very high gamma improve both training and validation accuracy? Compare the curved boundaries with the linear plot above. Gamma and C are different controls; changing one does not stand in for changing the other.

In [4]:
gamma_values=[0.01,0.1,1,10,100]
rbf_cases=[classifier_case(SVC(kernel="rbf",C=1,gamma=g),f"RBF SVM · C = 1 · gamma = {g}") for g in gamma_values]
rbf_fig=classifier_plot(rbf_cases,"Gamma (C=1): ",initial=2,margins=True)
rbf_fig.show()
display(pd.DataFrame([{"Kernel":"linear","Setting":c["label"],"Train":c["train_acc"],"Validation":c["val_acc"]}
    for c in linear_cases]+[{"Kernel":"RBF","Setting":c["label"],"Train":c["train_acc"],"Validation":c["val_acc"]}
    for c in rbf_cases]).round(3))

,Kernel,Setting,Train,Validation
0,linear,Linear SVM · C = 0.01,0.844,0.883
1,linear,Linear SVM · C = 0.1,0.844,0.883
2,linear,Linear SVM · C = 1,0.828,0.883
3,linear,Linear SVM · C = 10,0.839,0.883
4,linear,Linear SVM · C = 100,0.839,0.883
5,RBF,RBF SVM · C = 1 · gamma = 0.01,0.839,0.883
6,RBF,RBF SVM · C = 1 · gamma = 0.1,0.844,0.900
7,RBF,RBF SVM · C = 1 · gamma = 1,0.933,0.933
8,RBF,RBF SVM · C = 1 · gamma = 10,0.961,0.933
9,RBF,RBF SVM · C = 1 · gamma = 100,0.994,0.800


## Workshop exercise set (20–30 minutes)

For each exercise, record **prediction → action or calculation → evidence → explanation**. Exercises 1–4 are core; 5–6 work well for pairs or group discussion.

1. **Identify which points can influence the linear SVM boundary most.**
2. **Predict what larger C does before changing it.**
3. **Find a gamma value that clearly overfits the training geometry.**
4. **Explain why scaling changes the fitted SVM.**
5. **Compare linear and RBF kernels on the same split using validation evidence.**
6. **Choose a kernel for a small tabular dataset and state what evidence could reverse your choice.**

### Stretch challenges

1. Explain C as a cost tradeoff without using the word regularization.
2. Describe why probability estimates from an SVM require extra calibration.

## Instructor debrief

<details><summary>Reveal expected reasoning and misconception</summary>

Use these as discussion targets rather than scripts. Ask for evidence before revealing the explanation.

1. Points on or inside the margin, especially support vectors, determine the boundary.
2. Larger C penalizes violations more and usually narrows tolerance for mistakes.
3. Very large gamma creates highly local, irregular regions.
4. Margins and RBF distances depend on feature units.
5. Use held-out performance and boundary simplicity, not training accuracy alone.
6. Begin with a scaled linear baseline; validated nonlinear gains can justify RBF.

**Common misconception to surface:** A larger margin does not mean ignoring all classification errors.

A convincing learner explanation should name what changed, what stayed fixed, the evidence in the output, and one limit on the conclusion.

</details>

## When to use it

A linear SVM is worth considering when a straight boundary is a useful approximation. An RBF SVM can model curved boundaries on small or medium datasets. Both need deliberate feature scaling and validation. Kernel SVM training can become costly on large datasets. A more complex boundary is not automatically a better one.

The plotted contours approximate a fitted score on a finite grid. Very tiny regions can be smaller than a grid cell, especially with large gamma. Accuracy is calculated from model predictions on the actual examples, not from the picture.

## Practice

1. What changes when C increases?
2. Why can gamma=100 fit training details but generalize poorly?
3. Are support vectors selected from validation data?
4. Is an SVM decision score of 0.8 an 80% probability?

<details><summary>Reveal the explanations</summary>

1. Margin violations receive a larger penalty relative to regularization. It does not guarantee higher validation accuracy.
2. Very local influence can create a boundary tailored to individual training points and noise.
3. No. They come from training examples; validation data evaluates the result.
4. No. Decision scores are not probabilities. Probability estimation requires an additional calibrated mapping.

</details>

**Next:** [Clustering without labels](06_kmeans_and_dbscan.ipynb).